In [1]:
import duckdb
import pydeck as pdk

con = duckdb.connect("france.duckdb")
con.execute("LOAD spatial")

In [19]:
con.execute("""
    CREATE OR REPLACE TABLE stops_clean AS
    WITH c AS (
        SELECT city, median(lat) AS clat, median(lon) AS clon FROM v_stops GROUP BY city
    ),
    r AS (
        SELECT * FROM (VALUES ('paris', 30), ('lyon', 25), ('marseille', 20)) t(city, max_km)
    )
    SELECT s.city, s.stop_id, s.stop_name, s.lat, s.lon,
           111 * sqrt(power(s.lat - c.clat, 2) + power((s.lon - c.clon) * 0.7, 2)) AS km
    FROM v_stops s
    JOIN gtfs_stops g USING (city, stop_id)
    JOIN c USING (city)
    JOIN r USING (city)
    WHERE COALESCE(NULLIF(g.location_type, ''), '0') = '0'
      AND 111 * sqrt(power(s.lat - c.clat, 2) + power((s.lon - c.clon) * 0.7, 2)) <= r.max_km
""")
con.sql("SELECT city, COUNT(*) AS durak, round(MAX(km), 1) AS max_km FROM stops_clean GROUP BY 1").df()

,city,durak,max_km
0,paris,24486,30.0
1,lyon,7691,25.0
2,marseille,2748,11.9


In [20]:
con.execute("""
    CREATE OR REPLACE TABLE antennas_area AS
    SELECT DISTINCT a.* EXCLUDE (city), s.city
    FROM antennas a
    JOIN stops_clean s
      ON a.lat BETWEEN s.lat - 0.0045 AND s.lat + 0.0045
     AND a.lon BETWEEN s.lon - 0.0065 AND s.lon + 0.0065
""")
con.sql("""
    SELECT city, operator, COUNT(DISTINCT SUP_ID) AS direk
    FROM antennas_area GROUP BY 1, 2 ORDER BY 1, 2
""").df()

,city,operator,direk
0,lyon,Bouygues,658
1,lyon,Free,608
2,lyon,Orange,545
3,lyon,SFR,567
4,marseille,Bouygues,340
5,marseille,Free,275
6,marseille,Orange,274
7,marseille,SFR,422
8,paris,Bouygues,3400
9,paris,Free,3052


In [23]:
stops = con.sql("SELECT city, stop_name, lat, lon FROM stops_clean").df()
stops["label"] = "Durak: " + stops["stop_name"]

ant = con.sql("""
    SELECT DISTINCT SUP_ID, city, operator, techs, lat, lon
    FROM antennas_area
""").df()
ant["label"] = ant["operator"] + " – " + ant["techs"].fillna("bilinmiyor")

op_colors = {"Orange": [230, 159, 0], "SFR": [204, 121, 167], "Bouygues": [0, 114, 178], "Free": [0, 0, 0]}
ant["color"] = ant["operator"].map(op_colors)

In [24]:
stops_layer = pdk.Layer(
    "ScatterplotLayer", data=stops, get_position=["lon", "lat"],
    get_fill_color=[100, 100, 100, 190],
    get_radius=15, radius_min_pixels=1, radius_max_pixels=4,
    pickable=True,
)

ant_layer = pdk.Layer(
    "ScatterplotLayer", data=ant, get_position=["lon", "lat"],
    get_fill_color="color",
    get_radius=35, radius_min_pixels=2.5, radius_max_pixels=8,
    pickable=True,
)

deck = pdk.Deck(
    layers=[stops_layer, ant_layer],
    initial_view_state=pdk.ViewState(latitude=48.8566, longitude=2.3522, zoom=10.5),
    map_style="light",
    tooltip={"text": "{city}\n{label}"},
)

deck.to_html("france_map.html")
deck

{
  "initialViewState": {
    "latitude": 48.8566,
    "longitude": 2.3522,
    "zoom": 10.5
  },
  "layers": [
    {
      "@@type": "ScatterplotLayer",
      "data": [
        {
          "city": "lyon",
          "label": "Durak: L'Arbresle Gare",
          "lat": 45.832863,
          "lon": 4.618411,
          "stop_name": "L'Arbresle Gare"
        },
        {
          "city": "lyon",
          "label": "Durak: l'Arbresle Le Parc",
          "lat": 45.834868,
          "lon": 4.615845,
          "stop_name": "l'Arbresle Le Parc"
        },
        {
          "city": "lyon",
          "label": "Durak: l'Arbresle Le Parc",
          "lat": 45.834811,
          "lon": 4.615933,
          "stop_name": "l'Arbresle Le Parc"
        },
        {
          "city": "lyon",
          "label": "Durak: l'Arbresle Route de Paris",
          "lat": 45.837145,
          "lon": 4.613159,
          "stop_name": "l'Arbresle Route de Paris"
        },
        {
          "city": "lyon",
          "label": "Durak: l'Arbresle Route de Paris",
          "lat": 45.837688,
          "lon": 4.611667,
          "stop_name": "l'Arbresle Route de Paris"
        },
        {
          "city": "lyon",
          "label": "Durak: Ancy Le Bourg",
          "lat": 45.838137,
          "lon": 4.508993,
          "stop_name": "Ancy Le Bourg"
        },
        {
          "city": "lyon",
          "label": "Durak: Ancy Le Bourg",
          "lat": 45.838195,
          "lon": 4.508972,
          "stop_name": "Ancy Le Bourg"
        },
        {
          "city": "lyon",
          "label": "Durak: Ancy Le Cret",
          "lat": 45.836164,
          "lon": 4.491906,
          "stop_name": "Ancy Le Cret"
        },
        {
          "city": "lyon",
          "label": "Durak: Ancy Le Cret",
          "lat": 45.836228,
          "lon": 4.492011,
          "stop_name": "Ancy Le Cret"
        },
        {
          "city": "lyon",
          "label": "Durak: Ancy Le Couvent",
          "lat": 45.838185,
          "lon": 4.513857,
          "stop_name": "Ancy Le Couvent"
        },
        {
          "city": "lyon",
          "label": "Durak: Ancy Le Couvent",
          "lat": 45.838241,
          "lon": 4.513845,
          "stop_name": "Ancy Le Couvent"
        },
        {
          "city": "lyon",
          "label": "Durak: Ancy Carnoux",
          "lat": 45.835298,
          "lon": 4.536694,
          "stop_name": "Ancy Carnoux"
        },
        {
          "city": "lyon",
          "label": "Durak: Ancy Carnoux",
          "lat": 45.835271,
          "lon": 4.536757,
          "stop_name": "Ancy Carnoux"
        },
        {
          "city": "lyon",
          "label": "Durak: Ancy Chazallet",
          "lat": 45.83399,
          "lon": 4.504455,
          "stop_name": "Ancy Chazallet"
        },
        {
          "city": "lyon",
          "label": "Durak: Ancy Chazallet",
          "lat": 45.833932,
          "lon": 4.504481,
          "stop_name": "Ancy Chazallet"
        },
        {
          "city": "lyon",
          "label": "Durak: Ancy Matillon",
          "lat": 45.831191,
          "lon": 4.49709,
          "stop_name": "Ancy Matillon"
        },
        {
          "city": "lyon",
          "label": "Durak: Ancy Matillon",
          "lat": 45.831241,
          "lon": 4.497145,
          "stop_name": "Ancy Matillon"
        },
        {
          "city": "lyon",
          "label": "Durak: Ancy Le Mullin",
          "lat": 45.833104,
          "lon": 4.532223,
          "stop_name": "Ancy Le Mullin"
        },
        {
          "city": "lyon",
          "label": "Durak: Ancy Le Mullin",
          "lat": 45.833145,
          "lon": 4.53228,
          "stop_name": "Ancy Le Mullin"
        },
        {
          "city": "lyon",
          "label": "Durak: Ancy Le Mullin",
          "lat": 45.833095,
          "lon": 4.532204,
          "stop_name": "Ancy Le Mullin"
        },
        {
          "city": "lyon",
          "label": "Durak: Ancy Les

In [10]:
con.sql("""
    SELECT a.agency_name, COUNT(DISTINCT r.route_id) AS hat
    FROM gtfs_agency a JOIN gtfs_routes r USING (city, agency_id)
    WHERE a.city = 'lyon'
    GROUP BY 1 ORDER BY 2 DESC
""").df()

,agency_name,hat
0,TCL,811
1,NE PAS EXPORTER,1


In [13]:
con.sql("""
    WITH c AS (
        SELECT city, median(lat) AS clat, median(lon) AS clon FROM v_stops GROUP BY city
    )
    SELECT s.city, s.stop_name, s.lat, s.lon,
           round(111 * sqrt(power(s.lat - c.clat, 2) + power((s.lon - c.clon) * 0.7, 2)), 1) AS km
    FROM v_stops s JOIN c USING (city)
    QUALIFY row_number() OVER (PARTITION BY s.city ORDER BY km DESC) <= 5
    ORDER BY s.city, km DESC
""").df()

,city,stop_name,lat,lon,km
0,lyon,Charlieu Lycée Notre Dame,46.163017,4.172308,64.1
1,lyon,Charlieu Lycée Notre Dame,46.163017,4.172308,64.1
2,lyon,Charlieu Ecole Ste Marie / CAT,46.156976,4.167084,64.0
3,lyon,Charlieu Ecole Ste Marie / CAT,46.156976,4.167084,64.0
4,lyon,Aigueperse Les Sarrets,46.285300,4.420400,63.7
5,marseille,Vallon de la Gazelle,43.406864,5.346371,11.9
6,marseille,Vallon de la Gazelle,43.407091,5.346309,11.9
7,marseille,Castors Isabella,43.405665,5.348457,11.7
8,marseille,Les Peyrets Fabrégoules,43.410113,5.371963,11.7
9,marseille,Chêne Vert,43.407226,5.354548,11.7
